# TOPKIDS dense-anchor articulation: true CLI-mirrored run

This notebook runs the real production lifecycle for TOPKIDS kid00:

    raw OFF mesh → 18 rendered views → fresh SAM 3D Body inference
    → established alignment/RANSAC path → robust joint triangulation
    → exact SAM surface-anchor triangulation → 1,000-step anchor fit
    → two-way Chamfer with early stopping → confidence-weighted fusion
    → production output handler

Hydra composes the same dense_anchor preset and algorithmic overrides as the CLI command under investigation: axis order yzx, all surface views, trim_mesh=false, and n_iters_anchors=1000. The only notebook-specific deviations are selecting one representative shape and writing to output/notebook_topkids_dense_anchor_e2e so existing CLI results are not overwritten.

No saved articulation, fitted MHR parameters, confidence sidecar, or replayed observations are used as input.

## 1. Repository and rendering setup

In [ ]:
import os
import sys
from pathlib import Path

os.environ.setdefault("PYOPENGL_PLATFORM", "egl")
os.environ.setdefault("MPLCONFIGDIR", "/tmp/matplotlib-cache")

def find_project_root(start=Path.cwd()):
    for candidate in (start, *start.parents):
        if (candidate / "pyproject.toml").is_file() and (candidate / "articulate").is_dir():
            return candidate
    fallback = Path("/home/knpob/work/code/atm-dev")
    if (fallback / "pyproject.toml").is_file():
        return fallback
    raise RuntimeError("Could not locate the atm-dev repository root.")

PROJECT_ROOT = find_project_root().resolve()
os.chdir(PROJECT_ROOT)  # Match the documented CLI launch directory.
if str(PROJECT_ROOT) not in sys.path:
    sys.path.insert(0, str(PROJECT_ROOT))
PROJECT_ROOT

In [ ]:
import time

import matplotlib.pyplot as plt
import numpy as np
import pyvista as pv
import torch
import trimesh
from hydra import compose, initialize_config_dir
from hydra.core.global_hydra import GlobalHydra
from hydra.utils import instantiate
from omegaconf import OmegaConf

from articulate.shape_refiner.dense_anchor_mhr_refiner import triangulation_covariances
from articulate.shape_refiner.mhr_refiner import (
    P_from_KRt,
    reprojection_errors_all,
    triangulate_with_robust_gating,
)

PYVISTA_BACKEND = "html"
pv.set_jupyter_backend(PYVISTA_BACKEND)
pv.global_theme.background = "white"
pv.global_theme.font.color = "black"

## 2. Compose the same Hydra preset and overrides

In [ ]:
SHAPE_NAME = "kid00"
RAW_DIR = PROJECT_ROOT / "data/shape-corr/TOPKIDS/off"
RAW_PATH = RAW_DIR / f"{SHAPE_NAME}.off"
NOTEBOOK_OUT_DIR = PROJECT_ROOT / "output/notebook_topkids_dense_anchor_e2e"
CLI_REFERENCE_PATH = PROJECT_ROOT / "output/topkids_anchor/mhr" / f"{SHAPE_NAME}.obj"

algorithmic_overrides = [
    "view_sampler.axis_order=yzx",
    "shape_refiner.n_views_surface=0",
    "shape_refiner.trim_mesh=false",
    "shape_refiner.n_iters_anchors=1000",
]
notebook_scope_overrides = [
    f"shape_dir={RAW_DIR}",
    f"out_dir={NOTEBOOK_OUT_DIR}",
    f"shape_loader.filename_filter={SHAPE_NAME}",
    "device=cuda:1",  # Matches output/topkids_anchor/.hydra/overrides.yaml.
]

if GlobalHydra.instance().is_initialized():
    GlobalHydra.instance().clear()
with initialize_config_dir(config_dir=str(PROJECT_ROOT / "articulate/config"), version_base=None):
    cfg = compose(
        config_name="dense_anchor",
        overrides=notebook_scope_overrides + algorithmic_overrides,
    )

required = [
    RAW_PATH,
    PROJECT_ROOT / cfg.shape_estimator.checkpoint_path,
    PROJECT_ROOT / cfg.shape_prior.mhr_path,
]
missing = [str(path) for path in required if not path.is_file()]
assert not missing, "Missing required assets: " + ", ".join(missing)
if str(cfg.device).startswith("cuda") and not torch.cuda.is_available():
    raise RuntimeError("The CLI-mirrored SAM 3D Body run requires an available CUDA device.")

assert cfg.view_sampler.axis_order == "yzx"
assert cfg.shape_refiner.n_views_surface == 0
assert cfg.shape_refiner.trim_mesh is False
assert cfg.shape_refiner.n_iters_anchors == 1000
assert cfg.shape_refiner.bone_term_weight == 0.0
assert cfg.shape_refiner.src_to_tgt and cfg.shape_refiner.tgt_to_src

print(OmegaConf.to_yaml(cfg, resolve=True))

In [ ]:
def as_polydata(vertices, faces):
    vertices = np.asarray(vertices)
    faces = np.asarray(faces, dtype=np.int64)
    pv_faces = np.column_stack([np.full(len(faces), 3), faces]).ravel()
    return pv.PolyData(vertices, pv_faces)

def set_parallel_view(plotter, view):
    getattr(plotter, f"view_{view}")()
    plotter.enable_parallel_projection()

def line_polydata(starts, ends):
    starts = np.asarray(starts)
    ends = np.asarray(ends)
    points = np.concatenate([starts, ends], axis=0)
    count = len(starts)
    lines = np.column_stack([np.full(count, 2), np.arange(count), np.arange(count) + count]).ravel()
    result = pv.PolyData(points)
    result.lines = lines
    return result

def sampled_surface_gap(source_mesh, target_mesh, sample_count=4096, seed=0):
    points, _ = trimesh.sample.sample_surface_even(source_mesh, sample_count, seed=seed)
    _, distances, _ = trimesh.proximity.closest_point(target_mesh, points)
    return float(np.mean(distances)), float(np.median(distances))

## 3. Instantiate and initialize the production components

This is the same initialization order used by articulate/run.py. A second refiner instance is used only for pre-optimization anchor inspection; the refiner that runs pipeline() remains untouched.

In [ ]:
shape_loader = instantiate(cfg.shape_loader)
view_sampler = instantiate(cfg.view_sampler)
shape_estimator = instantiate(cfg.shape_estimator)
shape_prior = instantiate(cfg.shape_prior)
shape_refiner = instantiate(cfg.shape_refiner)
diagnostic_refiner = instantiate(cfg.shape_refiner)
output_handler = instantiate(cfg.output_handler)

initialization_started = time.perf_counter()
shape_estimator.init_estimator()
shape_prior.load()
shape_prior.load_from_estimator(shape_estimator)
initialization_seconds = time.perf_counter() - initialization_started

shape_files = shape_loader.find_shape_files()
assert shape_files == [str(RAW_PATH)], shape_files
print(f"Initialized production models in {initialization_seconds:.1f} s")
print(f"Input:  {shape_files[0]}")
print(f"Output: {output_handler.out_dir}")

## 4. Load kid00 and render the production 18-view camera set

In [ ]:
shape = shape_loader.pipeline(shape_files[0])
raw_mesh = shape["mesh"]
camera_views = view_sampler.sample_views()
render_started = time.perf_counter()
view_sampling = view_sampler.pipeline(shape=shape, camera_views=camera_views)
render_seconds = time.perf_counter() - render_started

assert len(camera_views) == 18
assert len(view_sampling["observations"]) == 18
print(f"Raw mesh: {len(raw_mesh.vertices):,} vertices / {len(raw_mesh.faces):,} faces")
print(f"Rendered {len(camera_views)} views in {render_seconds:.1f} s")

In [ ]:
for view in ("xy", "yz", "zx"):
    plotter = pv.Plotter()
    plotter.add_mesh(as_polydata(raw_mesh.vertices, raw_mesh.faces), color="#bdbdbd", smooth_shading=True)
    plotter.add_title(f"Raw TOPKIDS {SHAPE_NAME} — {view}", font_size=10)
    set_parallel_view(plotter, view)
    plotter.show(jupyter_backend=PYVISTA_BACKEND)

## 5. Fresh SAM 3D Body inference and established alignment

Nothing is loaded from output/topkids_uncertainty or output/topkids_anchor. These results are produced now from the rendered RGB/depth observations.

In [ ]:
frontend_started = time.perf_counter()
shape_estimation = shape_estimator.pipeline(view_sampling=view_sampling)
frontend_seconds = time.perf_counter() - frontend_started
results = shape_estimation["results"]
view_keys = list(results.keys())

assert shape_estimation["shape"]["path"] == str(RAW_PATH)
assert len(results) >= 2
alignment_table = []
for view_key, result in results.items():
    confidence = result.get("confidence", {})
    alignment_table.append(
        (
            view_key,
            float(result["iou"]),
            float(confidence.get("alignment_rmse", np.nan)),
            int(confidence.get("num_inliers", 0)),
            float(confidence.get("inlier_ratio", np.nan)),
        )
    )

print(f"Fresh SAM/alignment views: {len(results)} / {len(camera_views)} in {frontend_seconds:.1f} s")
print("view             IoU       RMSE      inliers   ratio")
for row in alignment_table:
    print(f"{str(row[0]):16s} {row[1]:.4f}   {row[2]:.6f}   {row[3]:7d}   {row[4]:.4f}")

## 6. Exact production anchor selection and triangulation

The diagnostic refiner consumes the fresh result dictionary directly. The observations, visibility tests, Tukey-reweighted DLT triangulation, covariance gate, and minimum-view gate are the same helpers used by the production refiner.

In [ ]:
identity_coeffs, model_parameters, face_expr_coeffs = diagnostic_refiner.stack_mhr_params(
    results, cfg.device, dtype=torch.float32
)
canonical_vertices = diagnostic_refiner._neutral_template(
    shape_prior, identity_coeffs, model_parameters, face_expr_coeffs
)
faces = np.asarray(shape_estimation["estimator"].faces, dtype=np.int64)
anchor_indices = diagnostic_refiner._load_or_create_anchors(canonical_vertices, faces)
diagnostic_refiner._canonical_vertices = canonical_vertices
diagnostic_refiner._anchor_indices = anchor_indices

anchor_observations = diagnostic_refiner._anchor_observations(results, raw_mesh)
projection_matrices = diagnostic_refiner._projection_data(results)
triangulation_uv = anchor_observations.copy()
height = int(next(iter(results.values()))["cam"]["intrinsics"]["h"])
triangulation_uv[:, :, 1] = height - triangulation_uv[:, :, 1]
triangulated_anchors, used_anchor_views, anchor_confidence = triangulate_with_robust_gating(
    projection_matrices,
    triangulation_uv,
    sigma_px=diagnostic_refiner.anchor_pixel_sigma,
    conf_thresh=diagnostic_refiner.conf_thresh,
    n_iters=diagnostic_refiner.triangulation_iters,
)
anchor_covariances, anchor_support = triangulation_covariances(
    projection_matrices,
    triangulated_anchors,
    triangulation_uv,
    anchor_confidence,
    confidence_threshold=diagnostic_refiner.conf_thresh,
    pixel_sigma=diagnostic_refiner.anchor_pixel_sigma,
    damping=diagnostic_refiner.covariance_damping,
    uncertainty_floor=diagnostic_refiner.covariance_floor,
)
finite_anchors = np.all(np.isfinite(triangulated_anchors), axis=1)
final_anchor_mask = (
    finite_anchors
    & np.all(np.isfinite(anchor_covariances), axis=(1, 2))
    & (anchor_support >= diagnostic_refiner.min_anchor_views)
)

all_projected = []
for result in results.values():
    output = result["sam3d_output"]
    points = np.asarray(output["pred_vertices"])[anchor_indices] + np.asarray(output["pred_cam_t"])[None]
    focal = float(np.asarray(output["focal_length"]).reshape(-1)[0])
    cx, cy = result["cam"]["intrinsics"]["camera_center"]
    all_projected.append(
        np.column_stack([focal * points[:, 0] / points[:, 2] + cx, focal * points[:, 1] / points[:, 2] + cy])
    )
all_projected = np.stack(all_projected)
valid_observations = np.all(np.isfinite(anchor_observations), axis=2)

reprojection_errors, _ = reprojection_errors_all(
    projection_matrices, triangulated_anchors, triangulation_uv
)
final_inliers = (anchor_confidence >= diagnostic_refiner.conf_thresh) & np.isfinite(reprojection_errors)
median_reprojection = np.full(len(anchor_indices), np.nan)
for anchor_id in range(len(anchor_indices)):
    if np.any(final_inliers[:, anchor_id]):
        median_reprojection[anchor_id] = np.median(reprojection_errors[final_inliers[:, anchor_id], anchor_id])

print(f"Cached FPS anchors:       {len(anchor_indices):,}")
print(f"Usable 2D observations:  {valid_observations.sum():,} / {valid_observations.size:,}")
print(f"Finite triangulations:   {finite_anchors.sum():,}")
print(f"Finally selected:        {final_anchor_mask.sum():,}")
print(f"Rejected after 3D gate:  {(finite_anchors & ~final_anchor_mask).sum():,}")

In [ ]:
for view in ("xy", "yz", "zx"):
    plotter = pv.Plotter()
    plotter.add_mesh(as_polydata(canonical_vertices, faces), color="#b3cde3", opacity=0.62, smooth_shading=True)
    plotter.add_points(canonical_vertices[anchor_indices], color="#d7301f", point_size=5, render_points_as_spheres=True)
    plotter.add_title(f"1,024 cached geodesic-FPS anchors — {view}", font_size=10)
    set_parallel_view(plotter, view)
    plotter.show(jupyter_backend=PYVISTA_BACKEND)

In [ ]:
panel_ids = np.linspace(0, len(view_keys) - 1, min(4, len(view_keys)), dtype=int)
for view_index in panel_ids:
    view_key = view_keys[view_index]
    image = view_sampling["observations"][view_key]["rgb"]
    accepted = valid_observations[view_index]
    plt.figure(figsize=(5, 5))
    plt.imshow(image)
    plt.scatter(all_projected[view_index, :, 0], all_projected[view_index, :, 1], s=4, c="orange", alpha=0.18, label="all candidates")
    plt.scatter(anchor_observations[view_index, accepted, 0], anchor_observations[view_index, accepted, 1], s=7, c="lime", alpha=0.8, label="production-usable")
    plt.title(f"Fresh SAM anchor evidence {view_key}: {accepted.sum()} / 1024 usable")
    plt.xlim(0, 512)
    plt.ylim(512, 0)
    plt.axis("off")
    plt.legend(loc="lower left", fontsize=8)
    plt.show()

In [ ]:
plotter = pv.Plotter()
plotter.add_mesh(as_polydata(canonical_vertices, faces), color="#b3cde3", opacity=0.55, smooth_shading=True)
plotter.add_points(canonical_vertices[anchor_indices], color="#f16913", point_size=5, render_points_as_spheres=True)
plotter.add_title("All 1,024 canonical candidates", font_size=10)
set_parallel_view(plotter, "xy")
plotter.show(jupyter_backend=PYVISTA_BACKEND)

plotter = pv.Plotter()
plotter.add_mesh(as_polydata(raw_mesh.vertices, raw_mesh.faces), color="#d9d9d9", opacity=0.38, smooth_shading=True)
plotter.add_points(triangulated_anchors[finite_anchors], color="#f16913", point_size=6, render_points_as_spheres=True, label="all finite")
plotter.add_legend()
plotter.add_title(f"Fresh-SAM finite triangulations: {finite_anchors.sum()}", font_size=10)
set_parallel_view(plotter, "yz")
plotter.show(jupyter_backend=PYVISTA_BACKEND)

rejected_anchors = finite_anchors & ~final_anchor_mask
plotter = pv.Plotter()
plotter.add_mesh(as_polydata(raw_mesh.vertices, raw_mesh.faces), color="#d9d9d9", opacity=0.38, smooth_shading=True)
if np.any(rejected_anchors):
    plotter.add_points(triangulated_anchors[rejected_anchors], color="#d73027", point_size=7, render_points_as_spheres=True, label="rejected")
plotter.add_points(triangulated_anchors[final_anchor_mask], color="#1a9850", point_size=7, render_points_as_spheres=True, label="finally selected")
plotter.add_legend()
plotter.add_title(f"Production final anchor gate: {final_anchor_mask.sum()} selected", font_size=10)
set_parallel_view(plotter, "yz")
plotter.show(jupyter_backend=PYVISTA_BACKEND)

## 7. Run the untouched production refiner and output handler

This call starts from the fresh shape_estimation dictionary above. It includes robust joints, 1,000 sparse-anchor steps, two-way Chamfer with early stopping, and confidence-weighted fusion.

In [ ]:
refiner_started = time.perf_counter()
estimation_refined = shape_refiner.pipeline(
    shape_estimation=shape_estimation,
    shape_prior=shape_prior,
)
refiner_seconds = time.perf_counter() - refiner_started

output_handler.pipeline(estimation_refined=estimation_refined)
articulated_mesh = estimation_refined["mesh_merged"]

# The diagnostic and production refiner must see identical anchor evidence.
np.testing.assert_allclose(shape_refiner._anchor_targets, triangulated_anchors, rtol=1e-7, atol=1e-8, equal_nan=True)
np.testing.assert_array_equal(shape_refiner._anchor_valid, final_anchor_mask)
assert shape_refiner.bone_term_weight == 0.0
assert (output_handler.out_dir / "mhr" / f"{SHAPE_NAME}.obj").is_file()
assert (output_handler.out_dir / "mhr" / f"{SHAPE_NAME}.confidence.npz").is_file()

confidence = estimation_refined["confidence"]
optimization_summary = {
    "fresh_sam_views": len(results),
    "accepted_anchors": int(np.asarray(confidence["accepted_anchor_count"]).item()),
    "grounded_anchors": int(np.asarray(confidence["grounded_anchor_count"]).item()),
    "dense_steps": int(np.asarray(confidence["dense_steps"]).item()),
    "dense_stop_reason": str(np.asarray(confidence["dense_stop_reason"]).item()),
    "initial_validation_chamfer": float(np.asarray(confidence["dense_initial_validation_chamfer"]).item()),
    "best_dense_score": float(np.asarray(confidence["dense_best_score"]).item()),
    "bone_term_weight": float(shape_refiner.bone_term_weight),
    "frontend_seconds": float(frontend_seconds),
    "refiner_seconds": float(refiner_seconds),
    "written_mesh": str(output_handler.out_dir / "mhr" / f"{SHAPE_NAME}.obj"),
}
optimization_summary

In [ ]:
ground_targets, ground_normals, grounded_mask, body_diagonal = shape_refiner._grounding
line_ids = np.flatnonzero(grounded_mask)
if len(line_ids) > 250:
    line_ids = line_ids[np.linspace(0, len(line_ids) - 1, 250, dtype=int)]

plotter = pv.Plotter()
plotter.add_mesh(as_polydata(raw_mesh.vertices, raw_mesh.faces), color="#d9d9d9", opacity=0.38, smooth_shading=True)
plotter.add_points(shape_refiner._anchor_targets[shape_refiner._anchor_valid], color="#f16913", point_size=6, render_points_as_spheres=True, label="triangulated")
if len(line_ids):
    plotter.add_mesh(line_polydata(shape_refiner._anchor_targets[line_ids], ground_targets[line_ids]), color="#756bb1", line_width=1, label="nearest-raw gap")
plotter.add_legend()
plotter.add_title("Production triangulations and raw-surface grounding", font_size=10)
set_parallel_view(plotter, "yz")
plotter.show(jupyter_backend=PYVISTA_BACKEND)

## 8. Raw–articulated comparison from this exact run

Every PyVista direction is a separate scene for compatibility with the HTML backend. Gray is the raw scan and red is the newly produced articulation.

In [ ]:
raw_diagonal = max(float(np.linalg.norm(np.ptp(raw_mesh.bounds, axis=0))), 1e-12)
model_to_raw = sampled_surface_gap(articulated_mesh, raw_mesh, seed=0)
raw_to_model = sampled_surface_gap(raw_mesh, articulated_mesh, seed=1)
comparison_metrics = {
    "model_to_raw_mean/body_diagonal": model_to_raw[0] / raw_diagonal,
    "model_to_raw_median/body_diagonal": model_to_raw[1] / raw_diagonal,
    "raw_to_model_mean/body_diagonal": raw_to_model[0] / raw_diagonal,
    "raw_to_model_median/body_diagonal": raw_to_model[1] / raw_diagonal,
    "two_way_mean/body_diagonal": 0.5 * (model_to_raw[0] + raw_to_model[0]) / raw_diagonal,
}

if CLI_REFERENCE_PATH.is_file():
    cli_reference_mesh = trimesh.load(CLI_REFERENCE_PATH, process=False)
    notebook_to_cli = sampled_surface_gap(articulated_mesh, cli_reference_mesh, seed=2)
    cli_to_notebook = sampled_surface_gap(cli_reference_mesh, articulated_mesh, seed=3)
    comparison_metrics["notebook_vs_existing_cli_two_way_mean/body_diagonal"] = (
        0.5 * (notebook_to_cli[0] + cli_to_notebook[0]) / raw_diagonal
    )

for view in ("xy", "yz", "zx"):
    plotter = pv.Plotter()
    plotter.add_mesh(as_polydata(raw_mesh.vertices, raw_mesh.faces), color="#bdbdbd", opacity=0.38, smooth_shading=True, label="raw TOPKIDS")
    plotter.add_mesh(as_polydata(articulated_mesh.vertices, articulated_mesh.faces), color="#d7301f", opacity=0.62, smooth_shading=True, label="fresh dense-anchor result")
    plotter.add_legend()
    plotter.add_title(f"True end-to-end raw vs articulated — {view}", font_size=10)
    set_parallel_view(plotter, view)
    plotter.show(jupyter_backend=PYVISTA_BACKEND)

comparison_metrics

In [ ]:
_, vertex_gap, _ = trimesh.proximity.closest_point(raw_mesh, articulated_mesh.vertices)
distance_mesh = as_polydata(articulated_mesh.vertices, articulated_mesh.faces)
distance_mesh["nearest raw gap / body diagonal"] = vertex_gap / raw_diagonal

for view in ("xy", "yz", "zx"):
    plotter = pv.Plotter()
    plotter.add_mesh(
        distance_mesh,
        scalars="nearest raw gap / body diagonal",
        cmap="magma",
        smooth_shading=True,
        scalar_bar_args={"title": "nearest raw gap / diagonal"},
    )
    plotter.add_mesh(as_polydata(raw_mesh.vertices, raw_mesh.faces), color="white", opacity=0.10, style="wireframe")
    plotter.add_title(f"Fresh dense result distance to raw — {view}", font_size=10)
    set_parallel_view(plotter, view)
    plotter.show(jupyter_backend=PYVISTA_BACKEND)

## Visual correctness checklist

- The composed config must show n_iters_anchors=1000, trim_mesh=false, n_views_surface=0, two Chamfer directions, and bone_term_weight=0.
- Fresh SAM/alignment should retain the same view keys and broadly similar IoU/inlier statistics as the CLI run.
- Orange candidate projections and green usable anchors must come from result[sam3d_output], not from any saved fitted mesh.
- The all-triangulated cloud should reveal any systematic infant-body bias before optimization; this is the key diagnostic the old replay concealed.
- The production refiner assertion checks that its internal triangulated targets and final gate exactly match the expanded diagnostic computation.
- Broad rejection or displacement around the head, abdomen, hands, or feet is meaningful for TOPKIDS; isolated two-face scan debris is not.
- The early-stop reason and step count should be interpreted together with the directional raw-surface gaps.
- The optional notebook-versus-existing-CLI metric should be small, but exact equality is not promised because Chamfer subsampling and GPU kernels are not globally seeded by the CLI.